# Structured request adaptation: LoRA versus QLoRA

This is the **executed full comparison**. Original code, outputs, execution counts and metadata are preserved; the surrounding explanations have been updated for publication. Read the [report](../results/run_001/report.md) for the concise results and [README](../README.md) for setup and recovery. Viewing saved outputs requires no installation or GPU.

The recorded run used two NVIDIA A40 GPUs, Python **3.12.3**, PyTorch **2.8.0+cu128**, BF16, five epochs, training microbatch **16**, accumulation **1**, evaluation batch **32** and seed **2027**. Both arms completed 3,600 optimizer updates. One paired seed supports a measured case study. Inspection of the saved predictions shows that 92.3% of unadapted NF4 outputs begin with code fences, which fail the strict JSON contract; this is not evidence of a general loss of language understanding.

For a new experiment, save a working copy, edit the path, and choose the full or development configuration described below before creating a run. Device selection is **CUDA → MPS → CPU**; two CUDA GPUs run separate arms concurrently, while one device runs them serially. Imports and saved-result exports do not start experiments.


Import standard-library notebook utilities.

In [54]:
import json
import os
import subprocess
import sys
from pathlib import Path

Set the project location for a **new execution**. The preserved code uses the original remote path. Replace it in your working copy with an absolute path such as `Path("/absolute/path/to/structured-request-adaptation")`. Viewing existing outputs does not require changing this cell.


In [55]:
PROJECT_ROOT = Path("/workspace/structured-request-adaptation")  # Edit for another location.
PROJECT_ROOT

PosixPath('/workspace/structured-request-adaptation')

Use the project directory as the working directory. This also recovers a kernel whose previous working directory was replaced.

In [56]:
os.chdir(PROJECT_ROOT)

Install requirements into the current notebook Python with pip. This cell installs packages only; it does not download models or run experiments. If pip updates packages already imported by this kernel, restart the kernel, rerun the imports/path cells above, then continue below. You can skip this install cell once installation has succeeded.

In [57]:
subprocess.check_call([sys.executable, "-m", "pip", "install", "-r", str(PROJECT_ROOT / "requirements.txt")])

Ignoring torch: markers 'sys_platform == "darwin"' don't match your environment
Ignoring kernels: markers 'sys_platform == "darwin"' don't match your environment


0

Make the project source modules available to the notebook.

In [58]:
sys.path.insert(0, str(PROJECT_ROOT))

Import the controller and typed configuration. These imports do not start experiments.

In [59]:
from src.launcher import ExperimentLauncher
from src.config import ExperimentConfig

Create the lightweight experiment controller.

In [60]:
launcher = ExperimentLauncher(PROJECT_ROOT)

Detect available devices in a worker using the current notebook Python. CUDA takes priority, then MPS, then CPU. Inspect the selected device(s), precision, execution mode and batch defaults.

In [61]:
hardware = launcher.inspect_hardware()
hardware

Started inspect_hardware (PID 2197). Log: /workspace/structured-request-adaptation/jobs/20260930T064536-inspect_hardware-dc5f1ede/worker.log
inspect_hardware: running, 0s


{'version': 1,
 'device': 'cuda',
 'gpus': {'0': {'index': 0,
   'name': 'NVIDIA A40',
   'uuid': 'GPU-4eb6d14b-bb1a-ef2e-40a8-0e5b03caf9cc',
   'total_memory': 47697690624,
   'capability': [8, 6]},
  '1': {'index': 1,
   'name': 'NVIDIA A40',
   'uuid': 'GPU-3a01765d-8b60-55ea-a83d-c70f8abb6586',
   'total_memory': 47697690624,
   'capability': [8, 6]}},
 'native_bf16': {'0': True, '1': True},
 'selected_gpu_indices': [0, 1],
 'parallel': True,
 'arm_gpu': {'lora': 0, 'qlora': 1},
 'arm_masks': {'lora': 'GPU-4eb6d14b-bb1a-ef2e-40a8-0e5b03caf9cc',
  'qlora': 'GPU-3a01765d-8b60-55ea-a83d-c70f8abb6586'},
 'compute_dtype': 'bfloat16',
 'use_grad_scaler': False,
 'minimum_gpu_memory_bytes': 47697690624,
 'batch_defaults': {'microbatch_size': 4,
  'gradient_accumulation': 4,
  'evaluation_batch_size': 8},
 'matched_gpus': True,
 'host': {'system': 'Linux',
  'machine': 'x86_64',
  'cpu_model': 'Intel(R) Xeon(R) Gold 6342 CPU @ 2.80GHz',
  'memory_bytes': 540644093952}}

### Choose settings before creating a new run

The code below records the completed **full** A40 run: five epochs, microbatch 16, accumulation 1 and evaluation batch 32. These explicit overrides should not be reused automatically on MPS, CPU or smaller GPUs.

For a new quick test, replace the code cell in your working copy with:

```python
config = ExperimentConfig.for_hardware(
    hardware,
    model_revision="989aa7980e4cf806f80c7fef2b1adb7bc71aa306",
    preset="development",
)
config
```

This selects 128 training requests, 32 validation requests and one epoch, while still acquiring the complete model. For a new full run with hardware defaults, change only `preset="development"` to `preset="full"` in that short example. Hardware defaults use microbatch 1 × accumulation 16 on MPS, CPU and smaller CUDA devices, or 4 × 4 on larger CUDA devices. The paired effective batch remains 16. Inspect both pilots before continuing.


In [62]:
config = ExperimentConfig.for_hardware(
    hardware,
    model_revision="989aa7980e4cf806f80c7fef2b1adb7bc71aa306",
    preset="full",
    microbatch_size=16,
    gradient_accumulation=1,
    evaluation_batch_size=32,
)
config

ExperimentConfig(protocol_version='1.0', preset='full', train_example_limit=None, validation_example_limit=None, model_id='Qwen/Qwen2.5-1.5B-Instruct', model_revision='989aa7980e4cf806f80c7fef2b1adb7bc71aa306', dataset_url='https://amazon-massive-nlu-dataset.s3.amazonaws.com/amazon-massive-dataset-1.1.tar.gz', locale='en-US', seed=2027, epochs=5, microbatch_size=16, gradient_accumulation=1, evaluation_batch_size=32, answer_only_logits=True, learning_rate=0.0002, adam_betas=(0.9, 0.999), adam_epsilon=1e-08, weight_decay=0.0, warmup_ratio=0.03, gradient_clip=1.0, lora_rank=16, lora_alpha=32, lora_dropout=0.05, target_modules=('q_proj', 'k_proj', 'v_proj', 'o_proj', 'gate_proj', 'up_proj', 'down_proj'), max_sequence_length=2048, max_new_tokens=256, checkpoint_interval=50, benchmark_requests=100, benchmark_warmup=5, benchmark_repetitions=3, telemetry_interval_seconds=0.1, expected_split_counts=(11514, 2033, 2974))

Choose a fresh run or explicitly name an existing compatible run. `RUN_TO_RESUME = None` deliberately allocates the next run number; it never resumes automatically. Do not change an existing run's configuration.

The archived `run_001` predates the added publication utilities. Its source identity must remain unchanged: do not reopen it through edited current source or replace its recorded hashes. Use the offline export instructions in the README to read that evidence; genuine resumption requires the original source snapshot, recorded environment and full local artifacts.


In [63]:
RUN_TO_RESUME = None  # Example: "run_001"

Create the run and record its hardware plan, or verify the explicitly named run and register a compatible replacement session. A change of device type, batching, precision, source or dependencies requires a fresh run.

In [64]:
run_record = launcher.run_action("create_run", config=config.to_dict()) if RUN_TO_RESUME is None else launcher.run_action("resume_session", run_name=RUN_TO_RESUME)
run_record

Started create_run (PID 2203). Log: /workspace/structured-request-adaptation/jobs/20260930T064539-create_run-9329eeb1/worker.log
create_run: running, 0s


{'action': 'create_run',
 'run_name': 'run_001',
 'result': {'path': '/workspace/structured-request-adaptation/runs/run_001',
  'config': {'protocol_version': '1.0',
   'preset': 'full',
   'train_example_limit': None,
   'validation_example_limit': None,
   'model_id': 'Qwen/Qwen2.5-1.5B-Instruct',
   'model_revision': '989aa7980e4cf806f80c7fef2b1adb7bc71aa306',
   'dataset_url': 'https://amazon-massive-nlu-dataset.s3.amazonaws.com/amazon-massive-dataset-1.1.tar.gz',
   'locale': 'en-US',
   'seed': 2027,
   'epochs': 5,
   'microbatch_size': 16,
   'gradient_accumulation': 1,
   'evaluation_batch_size': 32,
   'answer_only_logits': True,
   'learning_rate': 0.0002,
   'adam_betas': [0.9, 0.999],
   'adam_epsilon': 1e-08,
   'weight_decay': 0.0,
   'warmup_ratio': 0.03,
   'gradient_clip': 1.0,
   'lora_rank': 16,
   'lora_alpha': 32,
   'lora_dropout': 0.05,
   'target_modules': ['q_proj',
    'k_proj',
    'v_proj',
    'o_proj',
    'gate_proj',
    'up_proj',
    'down_proj'],
   

Reuse this exact run name throughout the notebook.

In [65]:
RUN_NAME = run_record["run_name"]
RUN_NAME

'run_001'

Acquire the official MASSIVE archive once into the project-level `data/` folder and verify the shared cache. Later runs reuse its verified archive, English JSONL and license. Missing or changed committed files stop acquisition instead of silently changing dataset identity.

In [66]:
dataset = launcher.run_action("acquire_dataset", run_name=RUN_NAME)
dataset

Started acquire_dataset (PID 2211). Log: /workspace/structured-request-adaptation/jobs/20260930T064543-acquire_dataset-70a7a5e1/worker.log
acquire_dataset: running, 0s


{'action': 'acquire_dataset',
 'run_name': 'run_001',
 'result': {'checksum_policy': 'SHA256 recorded at first HTTPS acquisition; no upstream checksum claimed',
  'dataset': 'MASSIVE',
  'files': {'LICENSE': 'c2e6ea015269147de02117ebdd91f30ef09831251f5345fa8365273b1db1d435',
   'archive.tar.gz': '4cba5faa11c71437928e17cb1b9b3d8b8e727e7ea363a3a9a8045e19c0491577',
   'en-US.jsonl': 'c70f75c6a543a26e249ec383df67733ad9b1066f6c0406c2e04a3f03356e407e'},
  'license': 'CC-BY-4.0',
  'license_source': 'https://github.com/alexa/massive/blob/main/NOTICE.md',
  'locale': 'en-US',
  'source_url': 'https://amazon-massive-nlu-dataset.s3.amazonaws.com/amazon-massive-dataset-1.1.tar.gz',
  'version': '1.1',
  'storage': 'project_shared',
  'project_relative_path': 'data/massive-1.1/en-US',
  'cache_manifest_sha256': '9485324593e608204eb03ae187428c0102b7f799a47a2ba8b21892e5ee627963'}}

### Prepare structured targets

Parse annotations, retain repeated slots, preserve official partitions, and audit duplicate requests. Gold annotations are never included in request prompts.


In [67]:
prepared = launcher.run_action("prepare_data", run_name=RUN_NAME)
prepared

Started prepare_data (PID 2217). Log: /workspace/structured-request-adaptation/jobs/20260930T064547-prepare_data-a26b1d95/worker.log
prepare_data: running, 0s


{'action': 'prepare_data',
 'run_name': 'run_001',
 'result': {'split_counts': {'train': 11514, 'validation': 2033, 'test': 2974},
  'novel_input_counts': {'train': 0, 'validation': 2022, 'test': 2948},
  'ontology_source': 'Training annotations only; held-out labels checked for membership',
  'split_policy': 'All official partitions and rows retained; no resplitting or deduplication',
  'preset': 'full',
  'consumption_policy': 'Complete official partitions',
  'novel_input_policy': 'Test normalized utterance absent from both train and validation; dev absent from train',
  'audit_normalization': 'NFKC, casefold, collapse whitespace; audit only',
  'duplicate_audit_counts': {'exact': {'duplicate_group_count': 88,
    'cross_split_group_count': 37,
    'conflicting_group_count': 9},
   'normalized': {'duplicate_group_count': 88,
    'cross_split_group_count': 37,
    'conflicting_group_count': 9}},
  'files': {'train.jsonl': '74821443d8cb3b29c8041c62559e02e3527861c25cef52e8e007a07a45e6b

### Inspect the data audit

Read the saved audit without starting another experiment.


In [68]:
data_audit = json.loads((PROJECT_ROOT / "runs" / RUN_NAME / "preparation" / "data.json").read_text())
data_audit

{'audit_normalization': 'NFKC, casefold, collapse whitespace; audit only',
 'consumption_policy': 'Complete official partitions',
 'duplicate_audit_counts': {'exact': {'conflicting_group_count': 9,
   'cross_split_group_count': 37,
   'duplicate_group_count': 88},
  'normalized': {'conflicting_group_count': 9,
   'cross_split_group_count': 37,
   'duplicate_group_count': 88}},
 'files': {'duplicate_audit.json': 'b13388531109aea668c148acc01af4f10dde4bc350675cb27960d0f6d24614fb',
  'ontology.json': 'fc60f3087c8d386180d31771767c79bc8b59cabe32fe407beef6b71fb2d57925',
  'test.jsonl': 'fa3a7cd9fb981efcb9a60ba04437538d47d5f09c5a166f01a6911e5af282e1bb',
  'train.jsonl': '74821443d8cb3b29c8041c62559e02e3527861c25cef52e8e007a07a45e6b1d7',
  'validation.jsonl': '08f452c3e9ff455bf3d31761319f48ddb4b0cc485637f31b512b72284acff7c1'},
 'novel_input_counts': {'test': 2948, 'train': 0, 'validation': 2022},
 'novel_input_policy': 'Test normalized utterance absent from both train and validation; dev absent

### Acquire the pinned model and tokenizer

Download the immutable Qwen revision into this run. This stage can take time on first execution.


In [69]:
model_inputs = launcher.run_action("acquire_model", run_name=RUN_NAME)
model_inputs

Started acquire_model (PID 2224). Log: /workspace/structured-request-adaptation/jobs/20260930T064553-acquire_model-bab823d2/worker.log
acquire_model: running, 0s


{'action': 'acquire_model',
 'run_name': 'run_001',
 'result': {'model_id': 'Qwen/Qwen2.5-1.5B-Instruct',
  'revision': '989aa7980e4cf806f80c7fef2b1adb7bc71aa306',
  'local_path': 'inputs/base_model',
  'tokenizer_path': 'inputs/tokenizer'}}

### Prepare NF4 on its assigned device

Create the saved double-quantized NF4 base using the QLoRA GPU. Later QLoRA evaluation reloads this snapshot and the unmerged adapter.


In [70]:
quantized_inputs = launcher.run_action("prepare_quantized_base", run_name=RUN_NAME)
quantized_inputs

Started prepare_quantized_base (PID 2284). Log: /workspace/structured-request-adaptation/jobs/20260930T064612-prepare_quantized_base-ae57ce24/worker.log
prepare_quantized_base: running, 0s


{'action': 'prepare_quantized_base',
 'run_name': 'run_001',
 'result': {'format': 'bitsandbytes_nf4_double_quant',
  'config': {'quant_method': 'bitsandbytes',
   '_load_in_8bit': False,
   '_load_in_4bit': True,
   'llm_int8_threshold': 6.0,
   'llm_int8_skip_modules': ['lm_head'],
   'llm_int8_enable_fp32_cpu_offload': False,
   'llm_int8_has_fp16_weight': False,
   'bnb_4bit_quant_type': 'nf4',
   'bnb_4bit_use_double_quant': True,
   'bnb_4bit_compute_dtype': 'bfloat16',
   'bnb_4bit_quant_storage': 'uint8',
   'load_in_4bit': True,
   'load_in_8bit': False},
  'layers': {'model.layers.0.self_attn.q_proj': {'quant_type': 'nf4',
    'nested': True,
    'blocksize': 64,
    'storage_dtype': 'torch.uint8',
    'compute_dtype': 'torch.bfloat16'},
   'model.layers.0.self_attn.k_proj': {'quant_type': 'nf4',
    'nested': True,
    'blocksize': 64,
    'storage_dtype': 'torch.uint8',
    'compute_dtype': 'torch.bfloat16'},
   'model.layers.0.self_attn.v_proj': {'quant_type': 'nf4',
    '

### Build prompts and tokenize

Tokenize each official partition with the fixed instruction, enforce sequence limits, and mask all prompt tokens from the training loss.


In [71]:
tokenization = launcher.run_action("tokenize_data", run_name=RUN_NAME)
tokenization

Started tokenize_data (PID 2364). Log: /workspace/structured-request-adaptation/jobs/20260930T064631-tokenize_data-38ac1c3d/worker.log
tokenize_data: running, 0s
tokenize_data: running, 30s
Tokenize train:  97%|█████████▋| 11124/11514 [00:23<00:00, 423.40request/s]


{'action': 'tokenize_data',
 'run_name': 'run_001',
 'result': {'max_sequence_length': 2048,
  'max_new_tokens': 256,
  'truncation': False,
  'loss_mask': 'Assistant JSON and EOS only; prompt/padding/template whitespace ignored',
  'splits': {'train': {'examples': 11514,
    'prompt_tokens': {'min': 517,
     'median': 523,
     'p95': 530,
     'max': 554,
     'mean': 523.4848011116901},
    'target_tokens': {'min': 10,
     'median': 20,
     'p95': 38,
     'max': 84,
     'mean': 20.364860170227548},
    'full_tokens': {'min': 528,
     'median': 543,
     'p95': 567,
     'max': 639,
     'mean': 544.8496612819176},
    'total_target_tokens': 234481,
    'total_input_tokens': 6273399},
   'validation': {'examples': 2033,
    'prompt_tokens': {'min': 517,
     'median': 523,
     'p95': 530,
     'max': 545,
     'mean': 523.4048204623709},
    'target_tokens': {'min': 10,
     'median': 20,
     'p95': 37,
     'max': 61,
     'mean': 20.35858337432366},
    'full_tokens': {'min

### Inspect answer-only masking

Show a prepared example and its supervised token boundaries before numerical checks.


In [72]:
masking_example = launcher.run_action("inspect_example", run_name=RUN_NAME)
masking_example

Started inspect_example (PID 2377). Log: /workspace/structured-request-adaptation/jobs/20260930T064721-inspect_example-b0742a43/worker.log
inspect_example: running, 0s


{'action': 'inspect_example',
 'run_name': 'run_001',
 'result': {'id': '1',
  'utterance': 'wake me up at nine am on friday',
  'target': {'intent': 'alarm_set',
   'slots': [{'type': 'time', 'value': 'nine am'},
    {'type': 'date', 'value': 'friday'}]},
  'prompt_tokens': 524,
  'full_tokens': 553,
  'supervised_tokens_including_eos': 28,
  'ignored_tokens': 525}}

### Inspect the architecture

Save model configuration, tensor shapes and adapter targets. Header inspection does not run training.


In [73]:
architecture = launcher.run_action("inspect_architecture", run_name=RUN_NAME)
architecture

Started inspect_architecture (PID 2383). Log: /workspace/structured-request-adaptation/jobs/20260930T064727-inspect_architecture-0821249e/worker.log
inspect_architecture: running, 0s


{'action': 'inspect_architecture',
 'run_name': 'run_001',
 'result': {'architecture_path': '/workspace/structured-request-adaptation/runs/run_001/preparation/architecture.json',
  'tensor_count': 338,
  'config': {'architectures': ['Qwen2ForCausalLM'],
   'attention_dropout': 0.0,
   'bos_token_id': 151643,
   'eos_token_id': 151645,
   'hidden_act': 'silu',
   'hidden_size': 1536,
   'initializer_range': 0.02,
   'intermediate_size': 8960,
   'max_position_embeddings': 32768,
   'max_window_layers': 21,
   'model_type': 'qwen2',
   'num_attention_heads': 12,
   'num_hidden_layers': 28,
   'num_key_value_heads': 2,
   'rms_norm_eps': 1e-06,
   'rope_theta': 1000000.0,
   'sliding_window': 32768,
   'tie_word_embeddings': True,
   'torch_dtype': 'bfloat16',
   'transformers_version': '4.43.1',
   'use_cache': True,
   'use_sliding_window': False,
   'vocab_size': 151936}}}

### Check LoRA on its assigned device

Create the single shared initial adapter and verify a synthetic forward/backward/update and adapter reconstruction. This is a compatibility check, not an experimental training epoch.


In [74]:
lora_preflight = launcher.run_action("preflight_lora", run_name=RUN_NAME)
lora_preflight

Started preflight_lora (PID 2389). Log: /workspace/structured-request-adaptation/jobs/20260930T064734-preflight_lora-27018e83/worker.log
preflight_lora: running, 0s


{'action': 'preflight_lora',
 'run_name': 'run_001',
 'result': {'passed': True,
  'synthetic_check': True,
  'rotary_precision': {'passed': True,
   'positions': [0, 255, 256, 257, 511, 512, 513, 639, 1023, 2047],
   'reference': 'Independent CPU FP32 frequency matmul and trigonometry',
   'maximum_absolute_errors': {'base_model.model.model.rotary_emb': {'torch.float32': 5.960464477539063e-08,
     'torch.bfloat16': 0.0}}},
  'gradients_finite': True,
  'frozen_base': True,
  'adapter_reload_parity': True,
  'inventory': {'targets': ['base_model.model.model.layers.0.self_attn.q_proj',
    'base_model.model.model.layers.0.self_attn.k_proj',
    'base_model.model.model.layers.0.self_attn.v_proj',
    'base_model.model.model.layers.0.self_attn.o_proj',
    'base_model.model.model.layers.0.mlp.gate_proj',
    'base_model.model.model.layers.0.mlp.up_proj',
    'base_model.model.model.layers.0.mlp.down_proj',
    'base_model.model.model.layers.1.self_attn.q_proj',
    'base_model.model.mode

### Check QLoRA on its assigned device

Load the same initial adapter into the saved NF4 model and verify numerical compatibility and reconstruction on its assigned GPU.


In [75]:
qlora_preflight = launcher.run_action("preflight_qlora", run_name=RUN_NAME)
qlora_preflight

Started preflight_qlora (PID 2584). Log: /workspace/structured-request-adaptation/jobs/20260930T064758-preflight_qlora-b0124bff/worker.log
preflight_qlora: running, 0s


{'action': 'preflight_qlora',
 'run_name': 'run_001',
 'result': {'passed': True,
  'synthetic_check': True,
  'rotary_precision': {'passed': True,
   'positions': [0, 255, 256, 257, 511, 512, 513, 639, 1023, 2047],
   'reference': 'Independent CPU FP32 frequency matmul and trigonometry',
   'maximum_absolute_errors': {'base_model.model.model.rotary_emb': {'torch.float32': 5.960464477539063e-08,
     'torch.bfloat16': 0.0}}},
  'gradients_finite': True,
  'frozen_base': True,
  'adapter_reload_parity': True,
  'inventory': {'targets': ['base_model.model.model.layers.0.self_attn.q_proj',
    'base_model.model.model.layers.0.self_attn.k_proj',
    'base_model.model.model.layers.0.self_attn.v_proj',
    'base_model.model.model.layers.0.self_attn.o_proj',
    'base_model.model.model.layers.0.mlp.gate_proj',
    'base_model.model.model.layers.0.mlp.up_proj',
    'base_model.model.model.layers.0.mlp.down_proj',
    'base_model.model.model.layers.1.self_attn.q_proj',
    'base_model.model.mod

### Commit the paired compatibility gate

Both device-specific preflights must pass with matching trainable parameter inventories before baseline or training jobs can start.


In [76]:
paired_preflight = launcher.run_action("preflight", run_name=RUN_NAME)
paired_preflight

Started preflight (PID 2717). Log: /workspace/structured-request-adaptation/jobs/20260930T064817-preflight-cafc5058/worker.log
preflight: running, 0s


{'action': 'preflight',
 'run_name': 'run_001',
 'result': {'passed': True,
  'arms': {'lora': {'adapter_reload_parity': True,
    'cuda_device': {'capability': [8, 6],
     'index': 0,
     'name': 'NVIDIA A40',
     'total_memory': 47697690624,
     'uuid': 'GPU-4eb6d14b-bb1a-ef2e-40a8-0e5b03caf9cc'},
    'device': 'cuda',
    'device_index': 0,
    'frozen_base': True,
    'gradients_finite': True,
    'initial_adapter_sha256': '66fa10ca124146f99460173a3312afde62d9deabb9f1243fb00842f85124a64b',
    'inventory': {'parameters': {'base_model.model.model.layers.0.mlp.down_proj.lora_A.default.weight': {'dtype': 'torch.float32',
       'numel': 143360,
       'shape': [16, 8960]},
      'base_model.model.model.layers.0.mlp.down_proj.lora_B.default.weight': {'dtype': 'torch.float32',
       'numel': 24576,
       'shape': [1536, 16]},
      'base_model.model.model.layers.0.mlp.gate_proj.lora_A.default.weight': {'dtype': 'torch.float32',
       'numel': 24576,
       'shape': [16, 1536]},
 

Start the LoRA pilot on its assigned device. Its updated adapter is discarded; main training checkpoints are untouched.

In [77]:
lora_pilot = launcher.start_arm(RUN_NAME, "lora", phase="pilot")

Started lora (PID 2724). Log: /workspace/structured-request-adaptation/jobs/20260930T064822-lora-eba5fc4c/worker.log


Schedule the QLoRA pilot. It starts concurrently when two CUDA devices are assigned, or is queued behind LoRA on a single device.

In [78]:
qlora_pilot = launcher.start_arm(RUN_NAME, "qlora", phase="pilot")

Started qlora (PID 2725). Log: /workspace/structured-request-adaptation/jobs/20260930T064822-qlora-d617e07b/worker.log


Wait for both pilots and inspect their activity, phase timings and memory. These measurements are workload samples, not a promise of total completion time. Continue below only after reviewing them against your budget.

In [79]:
pilot_results = launcher.wait([lora_pilot, qlora_pilot])
pilot_results

lora: running, 0s
qlora: running, 0s
lora: running, 30s
lora bounded pilot:  18%|█▊        | 4/22 [00:10<00:46,  2.57s/update]
qlora: running, 30s
qlora bounded pilot:  18%|█▊        | 4/22 [00:13<00:58,  3.24s/update]
lora: running, 60s
lora bounded pilot:  73%|███████▎  | 16/22 [00:41<00:15,  2.55s/update]
qlora: running, 60s
qlora bounded pilot:  59%|█████▉    | 13/22 [00:42<00:28,  3.20s/update]
lora: complete, 90s
lora bounded pilot: 100%|██████████| 22/22 [00:56<00:00,  2.56s/update]
qlora: running, 90s
qlora bounded pilot: 100%|██████████| 22/22 [01:10<00:00,  3.23s/update]


{'lora': {'action': 'run_arm_pilot',
  'run_name': 'run_001',
  'result': {'arm': 'lora',
   'completed': True,
   'disposable_adapter': True,
   'primary_training_changed': False,
   'checkpoint': 'initial',
   'warmup_updates': 2,
   'warmup_qualification': 'Excluded 2 optimizer warmup update(s); at least one measured update retained.',
   'measured_updates': 20,
   'microbatch_size': 16,
   'effective_batch_size': 16,
   'evaluation_batch_size': 32,
   'max_new_tokens': 256,
   'device': 'cuda',
   'compute_dtype': 'bfloat16',
   'use_grad_scaler': False,
   'loading_seconds': 6.7138587157242,
   'wall_seconds': 70.65168221201748,
   'training_examples': 11514,
   'validation_examples': 2033,
   'epochs': 5,
   'updates': [{'update': 1,
     'warmup': True,
     'seconds': 3.1291781701147556,
     'examples': 16,
     'target_tokens': 349,
     'loss': 0.7207382333312813,
     'gradient_norm': 7.285630226135254},
    {'update': 2,
     'warmup': True,
     'seconds': 2.4487432073801

Inspect the compact pilot summary. Training projections exclude loading, checkpoint writes, validation, test and benchmarks. Parallel training follows the slower arm; serial execution adds their times. Activity errors mean unavailable measurements, not zero utilization.

In [80]:
pilot_summary = {
    arm: {
        "measured_updates": record["result"]["measured_updates"],
        "median_seconds_per_update": record["result"]["training_projection"]["seconds_per_update_median"],
        "projected_training_only_hours": record["result"]["training_projection"]["training_compute_seconds_at_median"] / 3600,
        "validation_sample_examples": record["result"]["validation_sample"]["examples"],
        "validation_sample_generation_seconds": record["result"]["validation_sample"]["generation_seconds"],
        "maximum_observed_memory_bytes": record["result"]["activity"]["maximum_observed_memory_bytes"],
        "activity_sampling_errors": record["result"]["activity"]["sampling_errors"],
    }
    for arm, record in pilot_results.items()
}
pilot_summary

{'lora': {'measured_updates': 20,
  'median_seconds_per_update': 2.5285936172585934,
  'projected_training_only_hours': 2.5285936172585934,
  'validation_sample_examples': 32,
  'validation_sample_generation_seconds': 2.825347188860178,
  'maximum_observed_memory_bytes': {'rss_bytes': 2840190976,
   'cuda_allocated_bytes': 6291732480,
   'cuda_reserved_bytes': 8482979840},
  'activity_sampling_errors': []},
 'qlora': {'measured_updates': 20,
  'median_seconds_per_update': 3.198913175612688,
  'projected_training_only_hours': 3.198913175612688,
  'validation_sample_examples': 32,
  'validation_sample_generation_seconds': 3.9386573149822652,
  'maximum_observed_memory_bytes': {'rss_bytes': 2853134336,
   'cuda_allocated_bytes': 5165030912,
   'cuda_reserved_bytes': 7839154176},
  'activity_sampling_errors': []}}

Start unquantized-base validation on the LoRA device. With two CUDA GPUs, it can run alongside quantized-base validation; on one device, the controller queues the second arm.


In [81]:
lora_baseline = launcher.start_arm(RUN_NAME, "lora", phase="baseline")

Started lora (PID 3260). Log: /workspace/structured-request-adaptation/jobs/20260930T065003-lora-6a2ccfdc/worker.log


Start NF4-base validation on the QLoRA device. Inspect this baseline separately from the adapted model. The saved NF4 baseline produced code-fenced outputs on 92.3% of test requests. These correctly fail the strict raw-JSON contract; the primary scores are unchanged. See the public report for this saved-output diagnosis and its limits.


In [82]:
qlora_baseline = launcher.start_arm(RUN_NAME, "qlora", phase="baseline")

Started qlora (PID 3261). Log: /workspace/structured-request-adaptation/jobs/20260930T065003-qlora-26d79c8f/worker.log


### Wait for both baseline validation jobs

Display progress and saved log locations while both workers run. A worker failure stops its peer and raises an error. Interrupting this wait stops both processes; a subsequent invocation reuses committed stages and restarts an incomplete evaluation. Training checkpoint recovery applies to training, not partially generated baseline predictions.


In [83]:
baseline_results = launcher.wait([lora_baseline, qlora_baseline])
baseline_results

lora: running, 0s
qlora: running, 0s
lora: running, 30s
2033 validation: answer NLL:  31%|███▏      | 20/64 [00:16<00:35,  1.25batch/s]
qlora: running, 30s
2033 validation: answer NLL:  25%|██▌       | 16/64 [00:17<00:51,  1.07s/batch]
lora: running, 60s
2033 validation: answer NLL:  91%|█████████ | 58/64 [00:47<00:04,  1.23batch/s]
qlora: running, 60s
2033 validation: answer NLL:  69%|██████▉   | 44/64 [00:47<00:21,  1.06s/batch]
lora: running, 90s
2033 validation: greedy generation:   9%|▉         | 6/64 [00:24<04:04,  4.21s/batch]
qlora: running, 90s
2033 validation: answer NLL: 100%|██████████| 64/64 [01:08<00:00,  1.07s/batch]

2033 validation: greedy generation:   2%|▏         | 1/64 [00:04<04:59,  4.75s/batch]
lora: running, 120s
2033 validation: greedy generation:  19%|█▉        | 12/64 [00:53<03:59,  4.61s/batch]
qlora: running, 120s
2033 validation: greedy generation:  11%|█         | 7/64 [00:34<04:41,  4.94s/batch]
lora: running, 150s
2033 validation: greedy generation:  30

{'lora': {'action': 'run_arm_baseline',
  'run_name': 'run_001',
  'result': {'base': {'system': 'base',
    'split': 'validation',
    'metrics': {'example_count': 2033,
     'joint_exact_match': 0.05312346286276439,
     'exact_match': 0.05312346286276439,
     'json_valid_rate': 0.8155435317265125,
     'structure_valid_rate': 0.7515986227250369,
     'schema_valid_rate': 0.5932120019675357,
     'intent_accuracy': 0.32611903590752583,
     'intent_macro_f1': 0.3352227871944624,
     'slot_precision': 0.16618357487922705,
     'slot_recall': 0.1709741550695825,
     'slot_f1': 0.16854483096521314,
     'counts': {'json_valid': 1658,
      'structure_valid': 1528,
      'schema_valid': 1206,
      'joint_exact_match': 108,
      'intent_correct': 663,
      'slot_tp': 344,
      'slot_fp': 1726,
      'slot_fn': 1668,
      'missing_slots': 1397,
      'extra_slots': 1455,
      'wrong_values': 271},
     'failure_counts': {'extra_slots': 1105,
      'invalid_json': 375,
      'inval

Start LoRA training. With two CUDA devices it can run alongside QLoRA; on one device the controller queues the second arm. The recorded run uses five full epochs.


In [84]:
lora_training = launcher.start_arm(RUN_NAME, "lora", phase="training")

Started lora (PID 3412). Log: /workspace/structured-request-adaptation/jobs/20260930T065707-lora-40b5f954/worker.log


Start QLoRA training with the same initialization, data order and update budget. It runs concurrently only when a second CUDA GPU is assigned.


In [85]:
qlora_training = launcher.start_arm(RUN_NAME, "qlora", phase="training")

Started qlora (PID 3413). Log: /workspace/structured-request-adaptation/jobs/20260930T065707-qlora-b52a968f/worker.log


### Wait for both training jobs

Display progress and saved log locations while both workers run. Any worker failure stops its peer and raises an error. Interrupting this wait stops both processes; re-run the phase to recover from the last committed checkpoint.


In [86]:
training_results = launcher.wait([lora_training, qlora_training])
training_results

lora: running, 0s
qlora: running, 0s
lora: running, 30s
lora epoch 1/5:   0%|          | 2/720 [00:05<32:50,  2.74s/update, loss=0.6924]
qlora: running, 30s
qlora epoch 1/5:   0%|          | 3/720 [00:10<39:44,  3.32s/update, loss=0.8996]
lora: running, 60s
lora epoch 1/5:   2%|▏         | 14/720 [00:36<29:49,  2.53s/update, loss=0.3694]
qlora: running, 60s
qlora epoch 1/5:   2%|▏         | 12/720 [00:39<37:54,  3.21s/update, loss=0.6194]
lora: running, 90s
lora epoch 1/5:   3%|▎         | 25/720 [01:04<29:49,  2.58s/update, loss=0.2600]
qlora: running, 90s
qlora epoch 1/5:   3%|▎         | 21/720 [01:08<36:59,  3.17s/update, loss=0.4394]
lora: running, 120s
lora epoch 1/5:   5%|▌         | 37/720 [01:35<30:09,  2.65s/update, loss=0.1833]
qlora: running, 120s
qlora epoch 1/5:   4%|▍         | 31/720 [01:40<37:49,  3.29s/update, loss=0.2265]
lora: running, 150s
lora epoch 1/5:   7%|▋         | 49/720 [02:06<28:58,  2.59s/update, loss=0.2319]
qlora: running, 150s
qlora epoch 1/5:   6%|▌ 

{'lora': {'action': 'run_arm_training',
  'run_name': 'run_001',
  'result': {'completed': True,
   'arm': 'lora',
   'epochs_completed': 5,
   'optimizer_updates': 3600,
   'microbatch_size': 16,
   'gradient_accumulation': 1,
   'effective_batch_size': 16,
   'target_tokens_seen': 1172405,
   'examples_seen': 57570,
   'training_seconds': 9249.854290399235,
   'wall_seconds': 11185.990893645212,
   'memory': {'measurement': 'maximum_observed_samples',
    'sample_interval_seconds': 0.1,
    'samples': 2,
    'rss_bytes': 3149119488,
    'cuda_allocated_bytes': 7560002560,
    'cuda_reserved_bytes': 12855541760,
    'elapsed_seconds': 0.0016513369046151638,
    'system_swap_out_bytes_delta': 0,
    'system_swap_activity_observed': False,
    'sampling_errors': [],
    'qualification': 'RSS and device memory overlap; do not add them. Sampling may miss short-lived peaks. Swap is system-wide, not attributed to this process.'},
   'training_memory': {'measurement': 'maximum_observed_sampl

### Inspect LoRA saved history

Read saved epoch metrics only; this does not launch training. The five recorded epochs each include complete validation loss and generated-output metrics.


In [87]:
lora_history = [json.loads(path.read_text()) for path in sorted((PROJECT_ROOT / "runs" / RUN_NAME / "trials" / "lora" / "metrics").glob("epoch_??.json"))]
lora_history

[{'epoch': 1,
  'global_step': 720,
  'metrics': {'answer_nll_sum': 2874.210482496477,
   'answer_token_nll': 0.06944382523125654,
   'answer_tokens': 41389,
   'confusion_matrix': [{'count': 15,
     'prediction': 'alarm_query',
     'target': 'alarm_query'},
    {'count': 2, 'prediction': 'alarm_set', 'target': 'alarm_query'},
    {'count': 1, 'prediction': 'datetime_query', 'target': 'alarm_query'},
    {'count': 1, 'prediction': 'play_radio', 'target': 'alarm_query'},
    {'count': 13, 'prediction': 'alarm_remove', 'target': 'alarm_remove'},
    {'count': 1, 'prediction': 'general_quirky', 'target': 'alarm_remove'},
    {'count': 28, 'prediction': 'alarm_set', 'target': 'alarm_set'},
    {'count': 2, 'prediction': 'calendar_set', 'target': 'alarm_set'},
    {'count': 1, 'prediction': 'datetime_query', 'target': 'alarm_set'},
    {'count': 1, 'prediction': '__invalid__', 'target': 'audio_volume_down'},
    {'count': 5,
     'prediction': 'audio_volume_down',
     'target': 'audio_vo

### Inspect QLoRA saved history

Read saved epoch metrics only; this does not launch training. The final epoch remains the primary equal-budget comparison even when an earlier validation checkpoint scores better.


In [88]:
qlora_history = [json.loads(path.read_text()) for path in sorted((PROJECT_ROOT / "runs" / RUN_NAME / "trials" / "qlora" / "metrics").glob("epoch_??.json"))]
qlora_history

[{'epoch': 1,
  'global_step': 720,
  'metrics': {'answer_nll_sum': 2949.904941175715,
   'answer_token_nll': 0.07127267972591063,
   'answer_tokens': 41389,
   'confusion_matrix': [{'count': 15,
     'prediction': 'alarm_query',
     'target': 'alarm_query'},
    {'count': 2, 'prediction': 'alarm_set', 'target': 'alarm_query'},
    {'count': 1, 'prediction': 'datetime_query', 'target': 'alarm_query'},
    {'count': 1, 'prediction': 'play_music', 'target': 'alarm_query'},
    {'count': 13, 'prediction': 'alarm_remove', 'target': 'alarm_remove'},
    {'count': 1, 'prediction': 'general_quirky', 'target': 'alarm_remove'},
    {'count': 28, 'prediction': 'alarm_set', 'target': 'alarm_set'},
    {'count': 2, 'prediction': 'calendar_set', 'target': 'alarm_set'},
    {'count': 1, 'prediction': 'datetime_query', 'target': 'alarm_set'},
    {'count': 4,
     'prediction': 'audio_volume_down',
     'target': 'audio_volume_down'},
    {'count': 4,
     'prediction': 'audio_volume_up',
     'targ

### Freeze the final comparison

This cell runs only after both training processes have finished. It verifies matching update/token budgets and locks final checkpoint identities and generation settings before test access.


In [ ]:
frozen = launcher.run_action("freeze_evaluation", run_name=RUN_NAME)
frozen

Started freeze_evaluation (PID 5410). Log: /workspace/structured-request-adaptation/jobs/20260930T105337-freeze_evaluation-678b49e4/worker.log
freeze_evaluation: running, 0s


{'action': 'freeze_evaluation',
 'run_name': 'run_001',
 'result': {'schema_version': 1,
  'preset': 'full',
  'protocol_hash': 'aefee7abfcf195419f56120d8f79387213ddd4d566cea7f638b68addf32369b8',
  'model_revision': '989aa7980e4cf806f80c7fef2b1adb7bc71aa306',
  'primary_checkpoint': 'final',
  'generation': {'max_new_tokens': 256,
   'evaluation_batch_size': 32,
   'padding': 'Left-padded prompts with explicit attention masks',
   'do_sample': False,
   'num_beams': 1,
   'use_cache': True,
   'terminal_token_policy': 'Saved tokenizer eos_token_id and pad_token_id',
   'decoding': 'Strip terminal EOS/PAD only; retain other special tokens; no text repair',
   'inherited_configuration': {'bos_token_id': 151643,
    'pad_token_id': 151643,
    'do_sample': True,
    'eos_token_id': [151645, 151643],
    'repetition_penalty': 1.1,
    'temperature': 0.7,
    'top_p': 0.8,
    'top_k': 20,
    'transformers_version': '4.37.0'}},
  'systems': ['base', 'quantized_base', 'lora', 'qlora'],
  'a

Evaluate the unquantized base and final LoRA adapter on the official test set, sequentially within this arm. This requires the frozen full-run protocol; a development run reports official test evaluation as unavailable.


In [ ]:
lora_test = launcher.start_arm(RUN_NAME, "lora", phase="test")

Started lora (PID 5419). Log: /workspace/structured-request-adaptation/jobs/20260930T105401-lora-b4f9f6c9/worker.log


Evaluate the saved NF4 base and final unmerged QLoRA adapter on the official test set, sequentially within this arm. With two GPUs, the other arm can evaluate concurrently.


In [ ]:
qlora_test = launcher.start_arm(RUN_NAME, "qlora", phase="test")

Started qlora (PID 5420). Log: /workspace/structured-request-adaptation/jobs/20260930T105401-qlora-34f6d533/worker.log


### Wait for both test evaluation jobs

Display progress and saved log locations while both workers run. A worker failure stops its peer and raises an error. Interrupting this wait stops both processes. A subsequent invocation reuses committed stages and restarts an incomplete evaluation; it does not resume halfway through a predictions file.


In [ ]:
test_results = launcher.wait([lora_test, qlora_test])
test_results

lora: running, 0s
qlora: running, 0s
lora: running, 30s
2974 test: answer NLL:  18%|█▊        | 17/93 [00:13<01:00,  1.26batch/s]
qlora: running, 30s
2974 test: answer NLL:  14%|█▍        | 13/93 [00:14<01:25,  1.07s/batch]
lora: running, 60s
2974 test: answer NLL:  58%|█████▊    | 54/93 [00:43<00:31,  1.23batch/s]
qlora: running, 60s
2974 test: answer NLL:  44%|████▍     | 41/93 [00:44<00:56,  1.09s/batch]
lora: running, 90s
2974 test: answer NLL:  98%|█████████▊| 91/93 [01:13<00:01,  1.23batch/s]
qlora: running, 90s
2974 test: answer NLL:  74%|███████▍  | 69/93 [01:14<00:26,  1.10s/batch]
lora: running, 120s
2974 test: greedy generation:   6%|▋         | 6/93 [00:28<07:05,  4.89s/batch]
qlora: running, 120s
2974 test: answer NLL: 100%|██████████| 93/93 [01:39<00:00,  1.07s/batch]

2974 test: greedy generation:   0%|          | 0/93 [00:00<?, ?batch/s]
lora: running, 150s
2974 test: greedy generation:  13%|█▎        | 12/93 [00:57<06:37,  4.90s/batch]
qlora: running, 150s
2974 test: g

{'lora': {'action': 'run_arm_test',
  'run_name': 'run_001',
  'result': {'base': {'system': 'base',
    'split': 'test',
    'metrics': {'example_count': 2974,
     'joint_exact_match': 0.05682582380632145,
     'exact_match': 0.05682582380632145,
     'json_valid_rate': 0.8221250840618696,
     'structure_valid_rate': 0.7575655682582381,
     'schema_valid_rate': 0.5928043039677202,
     'intent_accuracy': 0.3285137861466039,
     'intent_macro_f1': 0.34803803351791274,
     'slot_precision': 0.14157824933687002,
     'slot_recall': 0.15168738898756662,
     'slot_f1': 0.14645858343337334,
     'counts': {'json_valid': 2445,
      'structure_valid': 2253,
      'schema_valid': 1763,
      'joint_exact_match': 169,
      'intent_correct': 977,
      'slot_tp': 427,
      'slot_fp': 2589,
      'slot_fn': 2388,
      'missing_slots': 1930,
      'extra_slots': 2131,
      'wrong_values': 458},
     'failure_counts': {'extra_slots': 1611,
      'invalid_json': 529,
      'invalid_struct

Benchmark the unquantized base and final LoRA adapter, one system at a time. Each uses the same 100 fixed validation requests, five warmups and three measured repetitions at batch size one.


In [ ]:
lora_benchmark = launcher.start_arm(RUN_NAME, "lora", phase="benchmark")

Started lora (PID 5748). Log: /workspace/structured-request-adaptation/jobs/20260930T111440-lora-86513a78/worker.log


Benchmark the saved NF4 base and final QLoRA adapter, one system at a time. With two GPUs the other arm can benchmark concurrently, so timings may include contention for shared CPU, RAM and storage.


In [ ]:
qlora_benchmark = launcher.start_arm(RUN_NAME, "qlora", phase="benchmark")

Started qlora (PID 5749). Log: /workspace/structured-request-adaptation/jobs/20260930T111440-qlora-33586812/worker.log


### Wait for both inference benchmark jobs

Display progress and saved log locations while both workers run. A worker failure stops its peer and raises an error. Interrupting this wait stops both processes. A subsequent invocation reuses committed stages and restarts an incomplete benchmark; compare synchronized request timings and generated lengths, not progress-bar averages alone.


In [ ]:
benchmark_results = launcher.wait([lora_benchmark, qlora_benchmark])
benchmark_results

lora: running, 0s
qlora: running, 0s
lora: running, 30s
base benchmark 1/3:   3%|▎         | 3/100 [00:02<00:59,  1.62request/s]
qlora: running, 30s
Loading weights: 100%|██████████| 338/338 [00:00<00:00, 915.91it/s]

quantized_base benchmark 1/3:   1%|          | 1/100 [00:01<02:33,  1.55s/request]
lora: running, 60s
base benchmark 1/3:  31%|███       | 31/100 [00:32<01:18,  1.14s/request]
qlora: running, 60s
quantized_base benchmark 1/3:  18%|█▊        | 18/100 [00:31<02:25,  1.78s/request]
lora: running, 90s
base benchmark 1/3:  57%|█████▋    | 57/100 [01:02<00:53,  1.24s/request]
qlora: running, 90s
quantized_base benchmark 1/3:  36%|███▌      | 36/100 [01:00<01:50,  1.73s/request]
lora: running, 120s
base benchmark 1/3:  81%|████████  | 81/100 [01:31<00:21,  1.15s/request]
qlora: running, 120s
quantized_base benchmark 1/3:  55%|█████▌    | 55/100 [01:31<01:11,  1.59s/request]
lora: running, 150s
base benchmark 2/3:   8%|▊         | 8/100 [00:07<01:36,  1.05s/request]
qlora: runnin

{'lora': {'action': 'run_arm_benchmark',
  'run_name': 'run_001',
  'result': {'base': {'system': 'base',
    'split': 'validation',
    'preset': 'full',
    'development_only': False,
    'requests_per_repetition': 100,
    'repetitions': 3,
    'warmup_requests': 5,
    'measured_requests': 300,
    'batch_size': 1,
    'latency_boundary': 'synchronized tokenize/device-transfer/generate/decode; excludes scoring and load',
    'median_seconds': 1.0522630775813013,
    'p95_seconds': 1.7430716585600752,
    'end_to_end_seconds': 346.0219580354169,
    'generation_seconds': 345.43776178499684,
    'generated_tokens': 13404,
    'generated_tokens_per_second': 38.737426017998665,
    'requests_per_second': 0.86699700129809,
    'observed_memory': {'measurement': 'maximum_observed_samples',
     'sample_interval_seconds': 0.1,
     'samples': 3431,
     'rss_bytes': 1866530816,
     'cuda_allocated_bytes': 4064040960,
     'cuda_reserved_bytes': 4129292288,
     'elapsed_seconds': 346.502

### Collect the comparison

Read verified saved results. Missing or failed stages remain explicit; collection never fills gaps by launching experiments.


In [ ]:
comparison = launcher.run_action("collect_results", run_name=RUN_NAME)
comparison

Started collect_results (PID 6043). Log: /workspace/structured-request-adaptation/jobs/20260930T113117-collect_results-f4aeb671/worker.log
collect_results: running, 0s


{'action': 'collect_results',
 'run_name': 'run_001',
 'result': {'run': 'run_001',
  'preset': 'full',
  'quality_scope': 'Official test set and novel-input subset, final equal-budget checkpoints',
  'expected': {'epochs_per_arm': 5,
   'benchmark_requests': 100,
   'benchmark_warmup': 5,
   'benchmark_repetitions': 3,
   'train_example_limit': None,
   'validation_example_limit': None,
   'test_enabled': True},
  'stages': {'acquire_model': {'ended_at': '2026-09-30T06:46:10.742474+00:00',
    'name': 'acquire_model',
    'started_at': '2026-09-30T06:45:58.683429+00:00',
    'status': 'complete'},
   'architecture': {'ended_at': '2026-09-30T06:47:33.854379+00:00',
    'name': 'architecture',
    'started_at': '2026-09-30T06:47:30.261361+00:00',
    'status': 'complete'},
   'arm_lora_baseline': {'ended_at': '2026-09-30T06:56:32.735403+00:00',
    'name': 'arm_lora_baseline',
    'started_at': '2026-09-30T06:50:06.153306+00:00',
    'status': 'complete'},
   'arm_lora_benchmark': {'end

### Generate training and validation loss

Generate one figure from saved measurements. Concurrent execution and one-seed limitations apply.


In [ ]:
plot_losses_result = launcher.run_action("plot_losses", run_name=RUN_NAME)
plot_losses_result

Started plot_losses (PID 6051). Log: /workspace/structured-request-adaptation/jobs/20260930T113138-plot_losses-9f7e4cf0/worker.log
plot_losses: running, 0s


{'action': 'plot_losses',
 'run_name': 'run_001',
 'result': '/workspace/structured-request-adaptation/runs/run_001/figures/losses.png'}

### Generate validation correctness and schema validity

Generate one figure from saved measurements. Concurrent execution and one-seed limitations apply.


In [ ]:
plot_validation_result = launcher.run_action("plot_validation", run_name=RUN_NAME)
plot_validation_result

Started plot_validation (PID 6063). Log: /workspace/structured-request-adaptation/jobs/20260930T113151-plot_validation-b0a17ec9/worker.log
plot_validation: running, 0s


{'action': 'plot_validation',
 'run_name': 'run_001',
 'result': '/workspace/structured-request-adaptation/runs/run_001/figures/validation.png'}

### Generate four-system task metrics

Generate one figure from saved measurements. Concurrent execution and one-seed limitations apply.


In [ ]:
plot_task_metrics_result = launcher.run_action("plot_task_metrics", run_name=RUN_NAME)
plot_task_metrics_result

Started plot_task_metrics (PID 6070). Log: /workspace/structured-request-adaptation/jobs/20260930T113203-plot_task_metrics-a6c33b2a/worker.log
plot_task_metrics: running, 0s


{'action': 'plot_task_metrics',
 'run_name': 'run_001',
 'result': '/workspace/structured-request-adaptation/runs/run_001/figures/task_metrics.png'}

### Generate observed memory and runtime

Generate one figure from saved measurements. Concurrent execution and one-seed limitations apply.


In [ ]:
plot_memory_runtime_result = launcher.run_action("plot_memory_runtime", run_name=RUN_NAME)
plot_memory_runtime_result

Started plot_memory_runtime (PID 6077). Log: /workspace/structured-request-adaptation/jobs/20260930T113215-plot_memory_runtime-742b34dd/worker.log
plot_memory_runtime: running, 0s


{'action': 'plot_memory_runtime',
 'run_name': 'run_001',
 'result': '/workspace/structured-request-adaptation/runs/run_001/figures/memory_runtime.png'}

### Generate prediction disagreements and failures

Generate one figure from saved measurements. Concurrent execution and one-seed limitations apply.


In [ ]:
plot_disagreements_result = launcher.run_action("plot_disagreements", run_name=RUN_NAME)
plot_disagreements_result

Started plot_disagreements (PID 6084). Log: /workspace/structured-request-adaptation/jobs/20260930T113227-plot_disagreements-14e78eb5/worker.log
plot_disagreements: running, 0s


{'action': 'plot_disagreements',
 'run_name': 'run_001',
 'result': '/workspace/structured-request-adaptation/runs/run_001/figures/disagreements.png'}

### Write the original technical report

This preserved action generated the run's original report from saved results, including device execution context and hardware provenance. Incomplete evidence never becomes a claimed result.

The [public report](../results/run_001/report.md) is a separately derived, readable publication. Its offline exporter reads the original archive without reopening the run through changed source. See the README for export and verification instructions; do not rerun completed GPU stages simply to regenerate publication files.


In [ ]:
report = launcher.run_action("write_report", run_name=RUN_NAME)
report

Started write_report (PID 6091). Log: /workspace/structured-request-adaptation/jobs/20260930T113239-write_report-7a144196/worker.log
write_report: running, 0s


{'action': 'write_report',
 'run_name': 'run_001',
 'result': '/workspace/structured-request-adaptation/runs/run_001/reports/results.md'}

List saved figures without regenerating results.

In [ ]:
figure_paths = sorted((PROJECT_ROOT / "runs" / RUN_NAME / "figures").glob("*.png"))
figure_paths

[PosixPath('/workspace/structured-request-adaptation/runs/run_001/figures/disagreements.png'),
 PosixPath('/workspace/structured-request-adaptation/runs/run_001/figures/losses.png'),
 PosixPath('/workspace/structured-request-adaptation/runs/run_001/figures/memory_runtime.png'),
 PosixPath('/workspace/structured-request-adaptation/runs/run_001/figures/task_metrics.png'),
 PosixPath('/workspace/structured-request-adaptation/runs/run_001/figures/validation.png')]

### Choose a prediction request

Optional: edit this request after completing the comparison. Prediction does not change adapters or evaluation settings.


In [ ]:
PREDICTION_REQUEST = "set an alarm for seven am"

### Reload QLoRA on its assigned device and predict

Reload the saved NF4 base and final unmerged QLoRA adapter on its assigned device, predict once, then release the model. The response is not repaired.


In [ ]:
prediction = launcher.run_action("predict", run_name=RUN_NAME, arm="qlora", text=PREDICTION_REQUEST)
prediction

Started predict (PID 6099). Log: /workspace/structured-request-adaptation/jobs/20260930T113251-predict-f899391b/worker.log
predict: running, 0s


{'action': 'predict',
 'run_name': 'run_001',
 'result': {'prediction_text': '{"intent":"alarm_set","slots":[{"type":"time","value":"seven am"}]}',
  'raw_continuation': '{"intent":"alarm_set","slots":[{"type":"time","value":"seven am"}]}<|im_end|>',
  'terminal_token_ids': [151645],
  'generated_token_ids': [4913,
   56431,
   3252,
   56780,
   2602,
   2198,
   49767,
   66582,
   1313,
   3252,
   1678,
   2198,
   957,
   3252,
   80185,
   1079,
   9207,
   13989,
   151645],
  'generated_tokens': 19,
  'prompt_tokens': 522,
  'post_eos_padding_tokens': 0,
  'hit_generation_limit': False,
  'generation_seconds': 1.7516902722418308,
  'end_to_end_seconds': 1.767099381890148,
  'json_valid': True,
  'structure_valid': True,
  'schema_valid': True,
  'parsed_prediction': {'intent': 'alarm_set',
   'slots': [{'type': 'time', 'value': 'seven am'}]},
  'failure_reasons': [],
  'system': 'qlora',
  'model_revision': '989aa7980e4cf806f80c7fef2b1adb7bc71aa306'}}

### Show run status and artifact locations

The saved output records the completed run. Preserve the full `runs/run_001/` archive together with shared `data/` when transferring resumable evidence. The public `results/run_001/` bundle contains the report and compact measurements, not model weights. Some later cells retain outputs with unset execution counters; committed worker result files independently establish completion.


In [ ]:
status = launcher.run_action("run_summary", run_name=RUN_NAME)
status

Started run_summary (PID 6183). Log: /workspace/structured-request-adaptation/jobs/20260930T113309-run_summary-ef2d7d10/worker.log
run_summary: running, 0s


{'action': 'run_summary',
 'run_name': 'run_001',
 'result': {'run': 'run_001',
  'preset': 'full',
  'quality_scope': 'Official test set and novel-input subset, final equal-budget checkpoints',
  'expected': {'epochs_per_arm': 5,
   'benchmark_requests': 100,
   'benchmark_warmup': 5,
   'benchmark_repetitions': 3,
   'train_example_limit': None,
   'validation_example_limit': None,
   'test_enabled': True},
  'stages': {'acquire_model': {'ended_at': '2026-09-30T06:46:10.742474+00:00',
    'name': 'acquire_model',
    'started_at': '2026-09-30T06:45:58.683429+00:00',
    'status': 'complete'},
   'architecture': {'ended_at': '2026-09-30T06:47:33.854379+00:00',
    'name': 'architecture',
    'started_at': '2026-09-30T06:47:30.261361+00:00',
    'status': 'complete'},
   'arm_lora_baseline': {'ended_at': '2026-09-30T06:56:32.735403+00:00',
    'name': 'arm_lora_baseline',
    'started_at': '2026-09-30T06:50:06.153306+00:00',
    'status': 'complete'},
   'arm_lora_benchmark': {'ended_a